# 09 — Tuning Familiar / Bridge / Adventurous by ear

Feedback from listening to notebook 08's tiers: Familiar is great, Bridge
sounds too close to Familiar, and Adventurous isn't far enough. The measured
cause of both: `tiers_for()`'s Bridge pool started scanning from rank 1 again
(so it could grab something as close as rank 2 if it merely lacked genre
overlap — no distance floor separating it from Familiar), and Adventurous used
`depth_for(0.85)` ≈ rank 197 of ~8,000 — the *2.5th percentile* of closeness,
not actually far.

## Working definitions

- **Familiar** — very similar sounding. Often the same genre, not required.
- **Bridge** — a real step further in sound than Familiar, genre may or may
  not differ. The gap from Familiar has to be audible, not just "next in line
  that happens to lack a shared genre tag."
- **Adventurous** — clearly further still — genuinely different from the
  seed, but not so far that it stops being a recognisable extension of it
  (see the catalogue's own ceiling below).

## What the catalogue's own decay curve says

Genre agreement@10-per-band and mean distance, by rank band, full 7,994-track
EffNet catalogue, ~200 seeds/band across all 8 genres:

| rank band | agreement | mean distance |
|---|---:|---:|
| 1-10 | 0.62 | 0.240 |
| 11-30 | 0.55 | 0.285 |
| 31-100 | 0.51 | 0.326 |
| 101-300 | 0.45 | 0.376 |
| 301-1000 | 0.33 | 0.448 |
| 1001-3000 | 0.16 | 0.552 |
| 3001-7993 | 0.06 | 0.695 |

Two things this settles. First, ranks 11-30 barely differ from 1-10 — that's
exactly why Bridge glued itself to Familiar before; there's no real separation
until past rank ~30. Second, by rank 3000+ agreement (0.06) falls *below* the
~0.125 random baseline for 8 balanced genres — that's not adventurous, that's
the model actively pointing at opposite-sounding music. Pushing Adventurous
past roughly rank 2000 stops being "further out" and starts being "wrong."

**Starting proposal, to test by ear, not to treat as final:**

- Familiar: rank 1-15
- Bridge: rank 30-150 (the gap from 15-30 is deliberate — a buffer so Bridge
  can't land right next to Familiar)
- Adventurous: rank 500-2000

Change the ranges in the cell below and re-run to try anything else — that's
the point of this notebook.

In [1]:
import sys
sys.path.append("..")

import ast
import tempfile
import os
from pathlib import Path
import numpy as np
import pandas as pd
import essentia.standard as es
import soundfile as sf
from IPython.display import Audio, display

from modeling.data import load_fma
from modeling.effnet_recommender import EffNetRecommender
from modeling.connecting_factors import ConnectingFactors
from modeling.rhythm import audio_path

REPO_ROOT = Path.cwd().parent if Path.cwd().name == "notebooks" else Path.cwd()
pd.set_option("display.max_colwidth", 60)

tracks = load_fma("small")[1]
rec = EffNetRecommender.from_npz(REPO_ROOT / "data" / "effnet_embeddings_full.npz", tracks)
print(f"catalogue: {len(rec.track_ids_)} tracks")

genres_all = tracks[("track", "genres_all")].apply(ast.literal_eval)
genres_lookup = pd.read_csv(REPO_ROOT / "data" / "raw" / "fma_metadata" / "genres.csv", index_col=0)["title"]

cf = ConnectingFactors.build(tracks)


def genre_names(gids):
    return [genres_lookup.get(i, str(i)) for i in gids]

catalogue: 7994 tracks


In [2]:
PREVIEW_SECONDS = 20
TARGET_RMS = 0.08
MAX_GAIN = 4.0


def load_preview(path, seconds=PREVIEW_SECONDS):
    y = es.MonoLoader(filename=str(path), sampleRate=22050)()
    sr = 22050
    skip = min(10.0, 0.1 * len(y) / sr)
    start = int(skip * sr)
    end = min(start + int(seconds * sr), len(y))
    start = max(0, end - int(seconds * sr))
    clip = y[start:end]
    rms = float(np.sqrt(np.mean(clip ** 2))) or 1e-9
    gain = min(TARGET_RMS / rms, MAX_GAIN)
    return np.clip(clip * gain, -1.0, 1.0), sr


def play(path, label_text):
    print(label_text)
    clip, sr = load_preview(path)
    with tempfile.NamedTemporaryFile(suffix=".ogg", delete=False) as f:
        sf.write(f.name, clip, sr, format="OGG", subtype="VORBIS")
        tmp_path = f.name
    try:
        display(Audio(filename=tmp_path))
    finally:
        os.unlink(tmp_path)

## The tunable tier tool

`explore_tiers` takes explicit **rank ranges** for each tier — not "first N
that pass some filter" — so tiers are structurally separated by distance no
matter what connects them. Within a gated tier's rank range, it *prefers*
candidates connected by at least one factor from that tier's own allowed set
— falling back to the plain distance-ranked pool if fewer than `n` connected
candidates exist in that band, so a tight range never comes up empty.

Each tier gets its **own** allowed-factor set now, not one shared list —
`gate_factors={"Bridge": ("era",), "Adventurous": None}` (`None` = any of the
four). Current reasoning: genre is excluded from Bridge's gate entirely — a
Bridge pick sharing the seed's own genre tag isn't really bridging anywhere.
Geography is excluded too, deliberately, not because it doesn't matter but
because *requiring* a country match would stop Bridge from ever connecting two
very different countries — the opposite of what it's for. Era stays as the
one required anchor for now. `factors_between` still reports every factor that
actually applies to a pick (shown in full below), even ones not used to gate
it — so a Bridge pick can show `via ['genre', 'era']` when genre happened to
match too; only `era` decided whether it qualified.

**A second, separate knob**, because the era gate alone still let genre
dominate by coincidence — the Hip-Hop seed's era-gated Bridge pool was still
4/5 Hip-Hop, just because most tracks *near it in rank* also happen to share
its genre and era together. `max_same_genre_share` caps how much of a tier's
`genre_top` can match the seed's, applied *after* the era gate, so Bridge
draws from era-connected candidates but is pushed toward ones that also cross
into a different genre: `0.0` = never the seed's own genre, `0.25` = up to
roughly a quarter of picks may share it, `None` = no cap (today's default is
`{"Bridge": 0.25}`).

First version of this backfilled from the same-genre side whenever the
different-genre side ran short inside the tier's own rank band — which is
exactly what happened for the tightly-clustered Hip-Hop seed (Bridge came back
4/5 Hip-Hop, the cap silently overridden). Listened to it and decided against
that: **`widen_to` now extends the search for different-genre, still
gate-connected candidates further out in rank — past the tier's own band, but
not into the next tier's territory** — rather than giving up and reusing
same-genre picks. Same-genre candidates still only ever come from the tier's
own band; only the different-genre search widens. Default: Bridge widens up to
where Adventurous starts, so the two tiers stay conceptually distinct.

In [3]:
ALL_FACTORS = ("genre", "genre_lineage", "era", "geography")


def _genre_top(track_id):
    return tracks.loc[track_id, ("track", "genre_top")]


def _cap_same_genre(pool_idx, candidate_ids, seed_id, seed_genre, n, max_share,
                     allowed_set, rng, widen_to=None):
    """Split pool_idx by whether the candidate shares seed_genre. Same-genre
    picks only ever come from pool_idx itself, capped at floor(n * max_share).
    Different-genre picks come from pool_idx first; if that's not enough,
    search further out in rank (up to widen_to, exclusive) for more, applying
    the same allowed_set connection gate to anything found there."""
    pool_idx = list(pool_idx)
    if seed_genre is None or not pool_idx:
        # no genre to compare against (the external seed has none) -- fall
        # back to a plain n-sized sample, NOT the whole unfiltered band
        return list(rng.choice(pool_idx, size=min(n, len(pool_idx)), replace=False)) if pool_idx else []

    same = [i for i in pool_idx if _genre_top(candidate_ids[i]) == seed_genre]
    diff = [i for i in pool_idx if _genre_top(candidate_ids[i]) != seed_genre]
    max_same = int(np.floor(n * max_share))
    n_same = min(max_same, len(same))
    needed_diff = n - n_same

    if len(diff) < needed_diff and widen_to is not None and pool_idx and widen_to > pool_idx[-1]:
        for j in range(pool_idx[-1] + 1, widen_to):
            if len(diff) >= needed_diff:
                break
            if _genre_top(candidate_ids[j]) == seed_genre:
                continue
            if allowed_set is not None and seed_id is not None:
                if not (set(cf.factors_between(seed_id, candidate_ids[j])) & allowed_set):
                    continue
            diff.append(j)  # appended in rank order (closest-first), since j increases

    n_diff = min(needed_diff, len(diff))
    if n_same + n_diff < n:  # still short after widening -- backfill from same as a last resort
        n_same = min(len(same), n - n_diff)

    chosen = list(rng.choice(same, size=n_same, replace=False)) if n_same else []
    chosen += diff[:n_diff]  # keep closest-first rather than randomising the widened search
    return chosen if chosen else pool_idx[: min(n, len(pool_idx))]


def explore_tiers(seed_id=None, seed_vec=None, seed_artist=None,
                   familiar=(0, 15), bridge=(30, 150), adventurous=(500, 2000), n=5,
                   gate_factors=None, max_same_genre_share=None, widen_to=None, seed=0):
    gate_factors = gate_factors or {"Bridge": ("era",), "Adventurous": None}
    # 0.0 = Bridge can never share the seed's genre_top; 0.25 = up to ~1/4 of
    # picks may; None = no constraint (genre composition falls out of distance
    # + gate_factors alone, same as before this parameter existed)
    max_same_genre_share = {"Bridge": 0.25} if max_same_genre_share is None else max_same_genre_share
    # how far out (exclusive upper rank bound) a tier may search for
    # different-genre candidates once its own band runs short -- default caps
    # Bridge's widened search at the start of Adventurous, so it never quietly
    # turns into an Adventurous pick wearing a Bridge label
    widen_to = {"Bridge": adventurous[0]} if widen_to is None else widen_to

    if seed_vec is None:
        row = rec._position(seed_id)
        seed_vec = rec.embedding_.iloc[[row]]
    widen_values = [v for v in widen_to.values() if v is not None]
    search_n = max(adventurous[1] + 1, (max(widen_values) + 1) if widen_values else 0, 50)
    distances, idx = rec.index_.kneighbors(seed_vec, n_neighbors=search_n)
    distances, idx = distances[0], idx[0]
    if seed_id is not None:
        distances, idx = distances[1:], idx[1:]
    candidate_ids = rec.track_ids_[idx]

    if seed_artist is not None:
        artists = tracks.loc[candidate_ids, ("artist", "name")].to_numpy()
        keep = artists != seed_artist
        candidate_ids, distances = candidate_ids[keep], distances[keep]

    seed_genre = _genre_top(seed_id) if seed_id is not None else None

    rng = np.random.default_rng(seed)
    out = {}
    for label, (lo, hi) in [("Familiar", familiar), ("Bridge", bridge), ("Adventurous", adventurous)]:
        hi = min(hi, len(candidate_ids))
        pool_idx = np.arange(lo, hi)

        allowed = gate_factors.get(label) if label in gate_factors else "skip"
        allowed_set = set(allowed or ALL_FACTORS) if allowed != "skip" else None
        if allowed_set is not None and seed_id is not None and len(pool_idx):
            connected = [i for i in pool_idx if set(cf.factors_between(seed_id, candidate_ids[i])) & allowed_set]
            pool_for_pick = connected if len(connected) >= n else list(pool_idx)
        else:
            pool_for_pick = list(pool_idx)

        share = max_same_genre_share.get(label) if label in max_same_genre_share else None
        if share is not None:
            pick = _cap_same_genre(pool_for_pick, candidate_ids, seed_id, seed_genre, n, share,
                                    allowed_set, rng, widen_to=widen_to.get(label))
        else:
            pick = list(rng.choice(pool_for_pick, size=min(n, len(pool_for_pick)), replace=False)) if pool_for_pick else []
        pick = sorted(pick)
        factors = [cf.factors_between(seed_id, candidate_ids[i]) if seed_id is not None else [] for i in pick]
        out[label] = [(candidate_ids[i], distances[i], i + 1, f) for i, f in zip(pick, factors)]
    return out


def show_and_play(seed_path, seed_label, tiers):
    play(seed_path, seed_label)
    for label, items in tiers.items():
        for tid, d, rank, factors in items:
            m = tracks.loc[tid]
            g = genre_names(genres_all.get(tid, []))
            factor_tag = f" via {factors}" if factors else " (no connecting factor -- fallback)"
            play(audio_path(tid),
                 f"{label}  rank={rank}  distance={d:.3f}{factor_tag}  {m[('artist','name')]} — {m[('track','title')]}  "
                 f"[{m[('track','genre_top')]}] {cf.describe(tid)}")

### Round 1: the starting proposal, on the same three catalogue seeds as
notebooks 07/08 — Hip-Hop (coherent), Instrumental (best genre-agreement),
Pop (the incoherent one) — plus the external seed.

One limitation, not a bug: the external seed has no `genres_all`/era/country
of its own (it never went through FMA's metadata pipeline), so connecting
factors can't be computed for it — its Bridge/Adventurous picks fall back to
pure distance ranking every time, tagged "(no connecting factor -- fallback)"
below. That's expected for this seed specifically, not a sign the tool is
broken.

In [4]:
ROUND_SEEDS = [2, 40659, 3538]  # AWOL - Food; Albert Glasser - The Auction 2; Cryptacize - Say You Will

for seed_id in ROUND_SEEDS:
    m = tracks.loc[seed_id]
    tiers = explore_tiers(seed_id=seed_id, seed_artist=m[("artist", "name")])
    print(f"\n=== SEED {seed_id}  {m[('artist','name')]} — {m[('track','title')]}  [{m[('track','genre_top')]}] ===")
    show_and_play(audio_path(seed_id), "SEED", tiers)


=== SEED 2  AWOL — Food  [Hip-Hop] ===
SEED


Familiar  rank=4  distance=0.173 via ['genre', 'geography']  Hi-Rez — The Remedy (Prod. Joel Johnston)  [Hip-Hop] 2012, United States


Familiar  rank=5  distance=0.180 via ['genre', 'geography']  CM & Tha Silent Partner — What's It All For  [Hip-Hop] 2014, United States


Familiar  rank=7  distance=0.189 via ['genre', 'geography']  Hi-Rez — Throw It Up Ft. BDG (Prod. Joel Johnston)  [Hip-Hop] 2012, United States


Familiar  rank=8  distance=0.193 via ['genre', 'geography']  DJ Def Chad — The Remedy  [Hip-Hop] 2014, United States


...

Adventurous  rank=1262  distance=0.379 via ['genre']  Red Crickets — Dynamo  [Pop] 2016, Finland


Adventurous  rank=1424  distance=0.389 via ['geography']  Ann Alee — Infant Holy, Infant Lowly  [Experimental] 2012, United States


Adventurous  rank=1479  distance=0.392 via ['geography']  Long Hair — Queen Anne & Degraw  [Rock] 2012, United States


Adventurous  rank=1713  distance=0.406 via ['geography']  Noveller — Entering  [Experimental] 2011, United States


Adventurous  rank=1851  distance=0.413 via ['geography']  Melaena Cadiz — Swingin' Low  [Folk] 2011, United States


In [5]:
SEED_PATH = REPO_ROOT / "data" / "raw" / "youtube_tests" / "Y2Mate.is - Elyjah Slaps the Space.mp3"

external = np.load(REPO_ROOT / "data" / "processed" / "essentia_handoff" / "external_effnet_embeddings.npz",
                    allow_pickle=True)
ext_names, ext_platforms, ext_vecs = external["names"], external["platforms"], external["embeddings"]
ext_vecs_u = ext_vecs / np.linalg.norm(ext_vecs, axis=1, keepdims=True)
seed_idx = int(np.flatnonzero(ext_platforms == "seed")[0])
seed_vec_2d = ext_vecs_u[seed_idx].reshape(1, -1)

tiers = explore_tiers(seed_vec=seed_vec_2d)
print("=== SEED — Elyjah Slaps the Space (external) ===")
show_and_play(SEED_PATH, "SEED", tiers)

=== SEED — Elyjah Slaps the Space (external) ===
SEED


Familiar  rank=4  distance=0.218 (no connecting factor -- fallback)  Josh Spacek — Loaded  [Instrumental] United States


Familiar  rank=5  distance=0.218 (no connecting factor -- fallback)  Malaventura — Let's the kids play  [Pop] Spain


Familiar  rank=7  distance=0.227 (no connecting factor -- fallback)  Blue Ducks — Floss Suffers From Gamma Radiation  [Hip-Hop] (no era/geography data)


Familiar  rank=8  distance=0.246 (no connecting factor -- fallback)  ZOE.LEELA — Bridges  [Pop] 2009


...

Adventurous  rank=916  distance=0.494 (no connecting factor -- fallback)  Ryan Cullinane — Upside Of Looking Down  [Instrumental] (no era/geography data)


Adventurous  rank=1338  distance=0.525 (no connecting factor -- fallback)  DJ Spooky — Arctic Rhythms (Dubstep Mix)  [Electronic] 2013, United States


Adventurous  rank=1507  distance=0.537 (no connecting factor -- fallback)  C-Doc — Far Gone (Featuring DJ Def Chad) (Vocal)  [Hip-Hop] 2012


Adventurous  rank=1723  distance=0.549 (no connecting factor -- fallback)  Langax — Adrenaline Intro  [Electronic] 2016, Spain


Adventurous  rank=1900  distance=0.561 (no connecting factor -- fallback)  Pranavibes — Dream & Bass  [Instrumental] 2016, France


### Round 2 — change the numbers here and re-run

Nudge `familiar` / `bridge` / `adventurous` (the `(low_rank, high_rank)` rank
bands), `gate_factors` (which connecting factors are required per tier —
`None` means any of the four), `max_same_genre_share` (how much of a tier
may still share the seed's own `genre_top`, applied after the gate — `0.0` for
a hard "never the seed's genre" rule, `None` for no cap), and `widen_to` (how
far a tier may search for different-genre candidates once its own band runs
short — `None` per tier disables widening, back to the old backfill-from-same
behaviour) based on what round 1 sounded like, then re-run this cell. Repeat
until the three tiers feel right; whatever lands here is what should go into
the actual product code.

Current setting: Bridge requires **era only** (genre and geography deliberately
ungated — see above), is capped at **25% same-genre**, and widens its
different-genre search up to where Adventurous starts if its own band comes up
short.

In [6]:
familiar = (0, 15)
bridge = (30, 150)
adventurous = (500, 2000)
gate_factors = {"Bridge": ("era",), "Adventurous": None}
max_same_genre_share = {"Bridge": 0.25}
widen_to = {"Bridge": adventurous[0]}

for seed_id in ROUND_SEEDS:
    m = tracks.loc[seed_id]
    tiers = explore_tiers(seed_id=seed_id, seed_artist=m[("artist", "name")],
                           familiar=familiar, bridge=bridge, adventurous=adventurous,
                           gate_factors=gate_factors, max_same_genre_share=max_same_genre_share, widen_to=widen_to)
    print(f"\n=== SEED {seed_id}  {m[('artist','name')]} — {m[('track','title')]}  [{m[('track','genre_top')]}] ===")
    show_and_play(audio_path(seed_id), "SEED", tiers)

tiers = explore_tiers(seed_vec=seed_vec_2d, familiar=familiar, bridge=bridge, adventurous=adventurous,
                       gate_factors=gate_factors, max_same_genre_share=max_same_genre_share, widen_to=widen_to)
print("\n=== SEED — Elyjah Slaps the Space (external) ===")
show_and_play(SEED_PATH, "SEED", tiers)


=== SEED 2  AWOL — Food  [Hip-Hop] ===
SEED


Familiar  rank=4  distance=0.173 via ['genre', 'geography']  Hi-Rez — The Remedy (Prod. Joel Johnston)  [Hip-Hop] 2012, United States


Familiar  rank=5  distance=0.180 via ['genre', 'geography']  CM & Tha Silent Partner — What's It All For  [Hip-Hop] 2014, United States


Familiar  rank=7  distance=0.189 via ['genre', 'geography']  Hi-Rez — Throw It Up Ft. BDG (Prod. Joel Johnston)  [Hip-Hop] 2012, United States


Familiar  rank=8  distance=0.193 via ['genre', 'geography']  DJ Def Chad — The Remedy  [Hip-Hop] 2014, United States


...

Adventurous  rank=916  distance=0.494 (no connecting factor -- fallback)  Ryan Cullinane — Upside Of Looking Down  [Instrumental] (no era/geography data)


Adventurous  rank=1338  distance=0.525 (no connecting factor -- fallback)  DJ Spooky — Arctic Rhythms (Dubstep Mix)  [Electronic] 2013, United States


Adventurous  rank=1507  distance=0.537 (no connecting factor -- fallback)  C-Doc — Far Gone (Featuring DJ Def Chad) (Vocal)  [Hip-Hop] 2012


Adventurous  rank=1723  distance=0.549 (no connecting factor -- fallback)  Langax — Adrenaline Intro  [Electronic] 2016, Spain


Adventurous  rank=1900  distance=0.561 (no connecting factor -- fallback)  Pranavibes — Dream & Bass  [Instrumental] 2016, France
